## setup

In [1]:
import os
import sys
sys.path.insert(0,'/root/eallmancy')
sys.path.insert(0,'/root/eallmancy/experiments')
os.chdir('/root/eallmancy')

# TODO: THIS IS ULTRA HACKY, PUT API SETTINGS IN CONTROL PANEL
with open('/root/openai_api_key') as f:
    os.environ['OPENAI_API_KEY'] = f.read().replace('\n','')
with open('/root/gemini_api_key') as f:
    os.environ['GEMINI_API_KEY'] = f.read().replace('\n','')

from eallmancy.engine.llm_solution_engine_v3 import EngineV3
from eallmancy import Artifact
from eallmancy import SinglePartSolution, ProblemSpec
from eallmancy.engine.engine_trace import EngineTrace
from collections import defaultdict
import datetime
import numpy as np
import os
import re




## benchmark analyzers (EmbeddingAnalysis)

In [2]:
from eallmancy.analysis.analyzer.utils import get_codet5p_embeddings, get_openai_embeddings, cosine_sim
from eallmancy.analysis.analyzer.analyzer import Analyzer

class PureEmbeddingAnalysis:
    def __init__(self, trace, embedding_func):
        all_solns = [a.trace_id for a in trace.list if a.is_solution]
        embs = embedding_func([CodeT5PAnalysis.get_clean_program(trace[ti]) for ti in all_solns])
        self.embs = {
            ti: emb for ti, emb in zip(all_solns, embs)
        }

    @classmethod
    def get_clean_program(cls, arte):
        return cls._clean_program(arte.program)
        
    @classmethod
    def _clean_program(cls, prog):
        # find function line
        fsig_idx = prog.find('def ')
        programbody_idx = fsig_idx + prog[fsig_idx:].find('\n')+1
        return prog[programbody_idx:]
        
    def distance(self, a, b):
        return 1 - cosine_sim(self.embs[a.trace_id], self.embs[b.trace_id])
        
class CodeT5PAnalysis(PureEmbeddingAnalysis):
    def __init__(self, trace):
        super().__init__(trace, embedding_func=get_codet5p_embeddings)
        
class OpenAIAnalysis(PureEmbeddingAnalysis):
    def __init__(self, trace):
        super().__init__(trace, embedding_func=get_openai_embeddings)

## analyzer pre-caching on disk

In [ ]:
%%time

from pathlib import Path
import re
import pickle as pk

TRACEVAULT_DIR = '/root/data/trace_vault'

def find_or_default(ptrn, tstr, flags=0, default=None):
    return (re.findall(ptrn, tstr, flags=flags) or [default]).pop()

def precache_traceanalyses(vault_name, ignore_newerthan=None, max_traceid=float('inf')):
    tracevault_dir = Path(TRACEVAULT_DIR) / vault_name
    traceanalysis_dir = Path('/root/data/cached_analyses') / vault_name
    
    for tid, trace_path in enumerate(tracevault_dir.glob('*.pk')):
        pk_filename = trace_path.name
        print(pk_filename)
        problem = find_or_default(r'_([^_,^\.]+)\.pk', pk_filename, default='')
        analyses_path = (traceanalysis_dir / pk_filename)
        if ignore_newerthan is not None and analyses_path.exists():
            if datetime.datetime.strptime(ignore_newerthan, '%Y-%m-%d_%H:%M:%S').timestamp() < os.path.getmtime(analyses_path):
                print('    skipping',pk_filename)
                continue
        try:
            trace = EngineTrace.load(trace_path)
        except:
            print('    failed to load, skipping')
            continue
        trace.trace_list = [a for a in trace.trace_list if a.trace_id <= max_traceid]
        for arte in trace.list:  # handle fudged solutions, scraped from reevo or llm4ad
            if arte.is_solution:
                if not hasattr(arte, 'program') and hasattr(arte, 'content'):
                    arte.program = find_or_default(r'```[^\n]*\n(.*?)```', arte.content , flags=re.DOTALL, default=arte.content )
    
        analyses = dict(
            elmcy=Analyzer.build_pairwise_analysis(trace, trace.problem_spec),
            codet5p=CodeT5PAnalysis(trace),
            openai=OpenAIAnalysis(trace),
        )
        
        with open(analyses_path.__str__(), 'wb') as f:
            pk.dump(analyses, f)

        del analyses # free up mem

def fetch_trace(vault_name, pk_filename, max_traceid=float('inf')):
    trace_fp = Path('/root/data/trace_vault') / vault_name / pk_filename
    trace = EngineTrace.load(trace_fp.__str__())
    trace.trace_list = [a for a in trace.trace_list if a.trace_id<=max_traceid]
    trace.trace_graph = trace.trace_graph.subgraph([a.trace_id for a in trace.trace_list])
    for arte in trace.list:  # handle fudged solutions, scraped from reevo or llm4ad
        if arte.is_solution:
            if not hasattr(arte, 'program') and hasattr(arte, 'content'):
                arte.program = find_or_default(r'```[^\n]*\n(.*?)```', arte.content , flags=re.DOTALL, default=arte.content )
    return trace

def fetch_traceanalyses(vault_name, pk_filename):
    traceanalysis_fp = Path('/root/data/cached_analyses') / vault_name / pk_filename
    with open(traceanalysis_fp.__str__(), 'rb') as f:
        all_ta = pk.load(f)
    return all_ta['elmcy'], all_ta['codet5p'], all_ta['openai']

# took 1h in total for og_benchmark
# precache_traceanalyses('og_benchmark', ignore_newerthan='2025-08-30_16:00:00')
# precache_traceanalyses('elmcy_reevo', ignore_newerthan='2025-08-31_16:00:00')
precache_traceanalyses('elmcy_eoh', ignore_newerthan='2025-08-30_20:00:00')
precache_traceanalyses('divrs_fs',    ignore_newerthan='2025-08-31_16:00:00', max_traceid=150)
# precache_traceanalyses('meta_eoh', ignore_newerthan='2025-08-31_16:00:00')


In [4]:
print(2)

2


## plot the whole narrative

### plot fitness-div convergence

In [32]:
import re
import polars as pl

def classify_operator(arte):
    if arte.__class__.__name__ != 'ThoughtfulSolution':
        return arte.__class__.__name__
    if re.search(r'I have one algorithm with its code as follows. Algorithm description:', arte.raw_query):
        # M1 or M2
        if re.search(r'assist me in creating a new algorithm that has a different parameter settings', arte.raw_query):
            return 'M2'
        else:
            return 'M1'
    elif re.search(r'existing algorithms with their codes as follows', arte.raw_query):
        # E1 or E2
        if re.search(r'totally different form from the given ones but can be motivated from them.', arte.raw_query):
            return 'E2'
        else:
            return 'E1'
    else:
        return 'I'

def trace_dist_matrixes_v2(trace, **dist_funcs):
    "dist_func needs to take two artifacts and figure out the rest"
    
    idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}
    
    _plotrows = []
    for a in range(len(idx_to_soln)):
        for b in range(len(idx_to_soln)):
            sa = idx_to_soln[a]
            sb = idx_to_soln[b]
            e = dict(
                a_idx=a, b_idx=b, a_tidx=idx_to_soln[a].trace_id, b_tidx=idx_to_soln[b].trace_id,
                a_fit=sa.fitness, b_fit=sb.fitness,
                a_is_parent=((idx_to_soln[a].trace_id,idx_to_soln[b].trace_id) in trace.graph.edges),
                b_is_parent=((idx_to_soln[b].trace_id,idx_to_soln[a].trace_id) in trace.graph.edges),
                b_operator=classify_operator(idx_to_soln[b]),
            )
            if a==b:
                for k,_ in dist_funcs.items():
                    e[f'dist_{k}'] = 0
            else:
                for k,dist_func in dist_funcs.items():
                    e[f'dist_{k}'] = dist_func(sa, sb)
            _plotrows.append(e)
    _plotdf = pl.DataFrame(_plotrows)
    return _plotdf


def traceid_cidx_map(trace, dist_func, thresh=0.1):
    solnid_to_cluster = dict()
    for cidx, cms in enumerate(shannon_wiener_clusters(trace.list, dist_func, thresh=thresh, max_trace_id=np.inf)):
        for m in cms:
            solnid_to_cluster[m.trace_id] = cidx
    return solnid_to_cluster

In [33]:
%%time

vault_name = 'divrs_fs'

all_dfs = []
for fn in os.listdir(TRACEVAULT_DIR+'/'+vault_name):
    trace = fetch_trace(vault_name, fn)
    trace.trace_list = [a for a in trace.trace_list if a.trace_id <= 150]
    elmcy_ta, codet5p_ta, openai_ta = fetch_traceanalyses(vault_name, fn)
    # cidx_map = traceid_cidx_map(trace, elmcy_ta.distance, thresh=0.10)
    df = (
        trace_dist_matrixes_v2(
            trace,
            elmcywt=elmcy_ta.distance,
            elmcyct=lambda a,b: elmcy_ta.distance(a,b, emb_mode='cutoff(0.05)'),
            jplag=lambda a,b: elmcy_ta.distance(a,b, emb_mode='ignore'),
            codet5p=codet5p_ta.distance,
            openai=openai_ta.distance
        )
        # .with_columns(elmcy_bcid=pl.col.b_tidx.replace(cidx_map))
        # .with_columns(elmcy_acid=pl.col.a_tidx.replace(cidx_map))
        # trace_inherit_df(trace, elmcy=elmcy_ta.distance, codet5p=codet5p_ta.distance, openai=openai_ta.distance)
        .with_columns(a_elminvalid=pl.col.a_tidx.is_in(elmcy_ta._invalid_solns))
        .with_columns(b_elminvalid=pl.col.b_tidx.is_in(elmcy_ta._invalid_solns))
        .with_columns(filename=pl.lit(fn))
        .with_columns(
            pl.col.filename.str.extract(r"[0-9]+-[0-9]+_[^_]+_[^_]+_([^\.]+)\.pk", 1).alias('problem'),
            pl.col.filename.str.extract(r"[0-9]+-[0-9]+_[^_]+_([^_]+)_[^\.]+\.pk", 1).alias('algo')
        )
    )
    all_dfs.append( df )

df = pl.concat(all_dfs)
    

CPU times: user 1min 2s, sys: 197 ms, total: 1min 2s
Wall time: 1min 2s


In [34]:
import plotly.express as px
from IPython.display import display


def dist_regularised(dist_col):
    return pl.col(dist_col) / pl.col(dist_col).max().over(['problem'])

def fitdivconv_plot(df, distname, regularised=False, granularity=0.101, cutoff=1.5):
    if regularised:
        distcol = dist_regularised(f'dist_{distname}')
    else:
        distcol = pl.col(f'dist_{distname}')

    fig = px.box(
        (
            df
            .filter(pl.col.a_fit != pl.lit(-float('inf')))
            .filter(pl.col.b_fit != pl.lit(-float('inf')))
            .with_columns(delta_fit=pl.col.a_fit - pl.col.b_fit)
            .with_columns(dist_bin=(distcol/granularity).round()*granularity)
            .filter(pl.col.dist_bin <= cutoff)
        ),
        x='dist_bin',
        y='delta_fit',
        facet_row='problem',
        # facet_col='b_operator',
        color='problem',
        height=1000,
        # box=True,
        points=False,
        boxmode='overlay',
        title=f'[{distname}] DivFit Convergence'
        # color='sim_idx'
    )
    # fig.update_traces(showwhiskers=False)  # no whiskers (min/max), just Q1–Q3 + median
    fig.update_yaxes(matches=None)
    # Remove whiskers (set whiskerwidth = 0 and showfliers = False)
    fig.update_traces(showwhiskers=False, boxpoints=False, whiskerwidth=0, quartilemethod="inclusive",)
    return fig

display( fitdivconv_plot(df, 'elmcywt', regularised=True, granularity=0.1001, cutoff=0.55) )
# display( fitdivconv_plot(df, 'elmcyct', regularised=True) )
# display( fitdivconv_plot(df, 'jplag', regularised=True) )
# display( fitdivconv_plot(df, 'codet5p', regularised=True) )
display( fitdivconv_plot(df, 'openai', regularised=True, granularity=0.1001, cutoff=0.55) )


### plot effective mutation rates

In [17]:
import re
import polars as pl

def classify_operator(arte):
    if arte.__class__.__name__ != 'ThoughtfulSolution':
        return arte.__class__.__name__
    if re.search(r'I have one algorithm with its code as follows. Algorithm description:', arte.raw_query):
        # M1 or M2
        if re.search(r'assist me in creating a new algorithm that has a different parameter settings', arte.raw_query):
            return 'M2'
        else:
            return 'M1'
    elif re.search(r'existing algorithms with their codes as follows', arte.raw_query):
        # E1 or E2
        if re.search(r'totally different form from the given ones but can be motivated from them.', arte.raw_query):
            return 'E2'
        else:
            return 'E1'
    else:
        return 'I'

def trace_dist_matrixes_v2(trace, **dist_funcs):
    "dist_func needs to take two artifacts and figure out the rest"
    
    idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}
    
    _plotrows = []
    for a in range(len(idx_to_soln)):
        for b in range(len(idx_to_soln)):
            sa = idx_to_soln[a]
            sb = idx_to_soln[b]
            e = dict(
                a_idx=a, b_idx=b, a_tidx=idx_to_soln[a].trace_id, b_tidx=idx_to_soln[b].trace_id,
                a_fit=sa.fitness, b_fit=sb.fitness,
                a_is_parent=((idx_to_soln[a].trace_id,idx_to_soln[b].trace_id) in trace.graph.edges),
                b_operator=classify_operator(idx_to_soln[b]),
            )
            if a==b:
                for k,_ in dist_funcs.items():
                    e[f'dist_{k}'] = 0
            else:
                for k,dist_func in dist_funcs.items():
                    e[f'dist_{k}'] = dist_func(sa, sb)
            _plotrows.append(e)
    _plotdf = pl.DataFrame(_plotrows)
    return _plotdf


def traceid_cidx_map(trace, dist_func, thresh=0.1):
    solnid_to_cluster = dict()
    for cidx, cms in enumerate(shannon_wiener_clusters(trace.list, dist_func, thresh=thresh, max_trace_id=np.inf)):
        for m in cms:
            solnid_to_cluster[m.trace_id] = cidx
    return solnid_to_cluster

In [47]:
%%time

vault_name = 'divrs_fs'

all_dfs = []
for fn in os.listdir(TRACEVAULT_DIR+'/'+vault_name):
    trace = fetch_trace(vault_name, fn)
    trace.trace_list = [a for a in trace.trace_list if a.trace_id <= 150]
    elmcy_ta, codet5p_ta, openai_ta = fetch_traceanalyses(vault_name, fn)
    # cidx_map = traceid_cidx_map(trace, elmcy_ta.distance, thresh=0.10)
    df = (
        trace_dist_matrixes_v2(
            trace,
            elmcywt=elmcy_ta.distance,
            elmcyct=lambda a,b: elmcy_ta.distance(a,b, emb_mode='cutoff(0.15)'),
            jplag=lambda a,b: elmcy_ta.distance(a,b, emb_mode='ignore'),
            codet5p=codet5p_ta.distance,
            openai=openai_ta.distance
        )
        .with_columns(a_elminvalid=pl.col.a_tidx.is_in(elmcy_ta._invalid_solns))
        .with_columns(b_elminvalid=pl.col.b_tidx.is_in(elmcy_ta._invalid_solns))
        # .with_columns(elmcy_bcid=pl.col.b_tidx.replace(cidx_map))
        # .with_columns(elmcy_acid=pl.col.a_tidx.replace(cidx_map))
        # trace_inherit_df(trace, elmcy=elmcy_ta.distance, codet5p=codet5p_ta.distance, openai=openai_ta.distance)
        .with_columns(filename=pl.lit(fn))
        .with_columns(
            pl.col.filename.str.extract(r"[0-9]+-[0-9]+_[^_]+_[^_]+_([^\.]+)\.pk", 1).alias('problem'),
            pl.col.filename.str.extract(r"[0-9]+-[0-9]+_[^_]+_([^_]+)_[^\.]+\.pk", 1).alias('algo')
        )
    )
    all_dfs.append( df )

df = pl.concat(all_dfs)
    

CPU times: user 1min 6s, sys: 227 ms, total: 1min 6s
Wall time: 1min 6s


In [48]:
import plotly.express as px
from IPython.display import display


def effmutrate_plot(df, _distcol, _gran=0.05):

    fig = px.bar(
        (
            df
            # .filter(pl.col.filename == '20250803-025521_cbf7_reevo_cvrp_aco.pk')
            .filter(pl.col.a_is_parent)
            .filter(~pl.col.b_elminvalid, ~pl.col.a_elminvalid)
            # .filter(~pl.col.b_classname.is_in(['EliteSolution'])) # exclude longterm reflction stuff
            .with_columns(pl.col('dist_'+_distcol).alias('dist'))
            .with_columns(((pl.col.dist / _gran).round() * _gran).alias('dist_bin'))
            .group_by(['problem', 'dist_bin']).agg(pl.col.b_fit.count().alias('count'))
            # .with_columns(((pl.col.b_idx / 5).round() * 5).alias('b_idx_bin'))
            .sort(['problem'])
        ),
        x='dist_bin',
        y='count',
        # color='filename',
        facet_row='problem',
        title=f'[{_distcol}] Effective Mutation Proba',
    )
    return fig
# fig.update_yaxes(matches=None, autorange=True)

display( effmutrate_plot(df, 'elmcywt') )
# display( effmutrate_plot(df, 'elmcyct') )
# display( effmutrate_plot(df, 'jplag') )
# display( effmutrate_plot(df, 'codet5p') )
display( effmutrate_plot(df, 'openai') )


## plot SWDI comparisons

In [56]:
import re
import polars as pl

def classify_operator(arte):
    if arte.__class__.__name__ != 'ThoughtfulSolution':
        return arte.__class__.__name__
    if re.search(r'I have one algorithm with its code as follows. Algorithm description:', arte.raw_query):
        # M1 or M2
        if re.search(r'assist me in creating a new algorithm that has a different parameter settings', arte.raw_query):
            return 'M2'
        else:
            return 'M1'
    elif re.search(r'existing algorithms with their codes as follows', arte.raw_query):
        # E1 or E2
        if re.search(r'totally different form from the given ones but can be motivated from them.', arte.raw_query):
            return 'E2'
        else:
            return 'E1'
    else:
        return 'I'



def trace_dist_matrixes_v2(trace, **dist_funcs):
    "dist_func needs to take two artifacts and figure out the rest"
    
    idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}
    
    _plotrows = []
    for a in range(len(idx_to_soln)):
        for b in range(a, len(idx_to_soln)):
            sa = idx_to_soln[a]
            sb = idx_to_soln[b]
            e = dict(
                a_idx=a, b_idx=b, a_tidx=idx_to_soln[a].trace_id, b_tidx=idx_to_soln[b].trace_id,
                a_fit=sa.fitness, b_fit=sb.fitness,
                a_is_parent=((idx_to_soln[a].trace_id,idx_to_soln[b].trace_id) in trace.graph.edges),
                b_operator=classify_operator(idx_to_soln[b]),
            )
            if a==b:
                for k,_ in dist_funcs.items():
                    e[f'dist_{k}'] = 0
            else:
                for k,dist_func in dist_funcs.items():
                    e[f'dist_{k}'] = dist_func(sa, sb)
            _plotrows.append(e)
    _plotdf = pl.DataFrame(_plotrows)
    return _plotdf

def shannon_wiener_clusters(arts, dist_func, thresh=0.1, max_trace_id=np.inf):
    clusters = [] # list of list of artifacts
    for a in arts:
        if not a.is_solution or a.trace_id > max_trace_id:
            continue

        for c_idx, cl in enumerate(clusters):
            if not any([dist_func(a, mem) > thresh for mem in cl]):
                clusters[c_idx].append(a)
                break
        else:
            clusters.append([a])  # new cluster
    return clusters

def traceid_cidx_map(trace, dist_func, thresh=0.1):
    solnid_to_cluster = dict()
    for cidx, cms in enumerate(shannon_wiener_clusters(trace.list, dist_func, thresh=thresh, max_trace_id=np.inf)):
        for m in cms:
            solnid_to_cluster[m.trace_id] = cidx
    return solnid_to_cluster

def trace_simple_v0(trace, **dist_funcs):
    
    idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}
    # cidx_maps = dict()
    # for k, dist_func in dist_funcs.items():
    #     cidx_maps[k] = traceid_cidx_map(trace, dist_func,
    
    _plotrows = []
    for b in range(len(idx_to_soln)):
        sb = idx_to_soln[b]
        e = dict(b_idx=b, b_tidx=sb.trace_id, b_fit=sb.fitness)
        _plotrows.append(e)
    return pl.DataFrame(_plotrows)


In [151]:
%%time

vault_name = 'elmcy_reevo'

import polars as pl


def _add_swdi_stats(ddf, trace, dist_f, prefix='dist_', thresh=0.15, rolling_window=20):
    cidx_map = traceid_cidx_map(trace, dist_f, thresh=thresh)
    cidx_colname = f'{prefix}cid'
    return (
        ddf
        .with_columns(
            pl.col.b_tidx.replace(cidx_map).alias(cidx_colname),
        )
        .sort(['filename', 'b_tidx'])  # ensure correct row order within each partition
        .with_columns(
            pl.col(cidx_colname)
            .cumulative_eval(                       # window grows 1 row at a time
                pl.element()                        # the current window (Series)
                  .value_counts()                   # struct[value, count]
                  .struct.field("count")            # take the counts only
                  .entropy(base=2.0, normalize=True)# H over counts (normalize=True ok)
            )
            .over(['filename'])                         # partition the running window
            .alias(f'{prefix}swdi_cumul')
        )
        .with_columns(
            pl.col(cidx_colname)
            .rolling_map(
            # .rolling(
                lambda s: (
                # (
                    s.value_counts()['count'].entropy(base=2.0, normalize=True)*1e5
                    # pl.element().value_counts()
                     # .struct.field("count")
                     #.entropy(base=2.0, normalize=True)
                ),
                window_size=rolling_window,
                min_samples=1,
                center=False,
            )
            # .over(["filename"])
            .alias(f"{prefix}swdi_rolling") / 1e5
        )
        .with_columns(pl.col.b_tidx.count().over(cidx_colname).alias(f'{prefix}clen'))
    )

obj_direction = (
    pl.when(pl.col.algo=='ogreevo')
    .then(
        pl.when(pl.col.problem.is_in(['tsp_aco', 'cvrp_aco'])).then(pl.lit('MIN')).otherwise(pl.lit('MAX'))
    )
    .otherwise(pl.lit('MAX'))
)
    
_ROLLING_MAX_FITNESS = (
    pl.col.b_fit
    .fill_nan(pl.lit(-float("inf")))
    .fill_null(pl.lit(-float("inf")))
    .rolling_max(window_size=int(1e9), min_samples=1)
    .sort_by(pl.col.b_tidx)
    # .over(pl.col.sim_idx, pl.col.algo, pl.col.problem_name)
)
_ROLLING_MIN_FITNESS = (
    pl.col.b_fit
    .fill_nan(pl.lit(-float("inf")))
    .fill_null(pl.lit(-float("inf")))
    .rolling_min(window_size=int(1e9), min_samples=1)
    .sort_by(pl.col.b_tidx)
    # .over(pl.col.sim_idx, pl.col.algo, pl.col.problem_name)
)

all_dfs = []
for fn in os.listdir(TRACEVAULT_DIR+'/'+vault_name):
    trace = fetch_trace(vault_name, fn)
    elmcy_ta, codet5p_ta, openai_ta = fetch_traceanalyses(vault_name, fn)
    # elmcyct_dist = lambda a,b: elmcy_ta.distance(a,b, emb_mode='cutoff(0.15)')
    jplag_dist = lambda a,b: elmcy_ta.distance(a,b, emb_mode='ignore')
    # cidx_map = traceid_cidx_map(trace, elmcy_ta.distance, thresh=0.15)
    df = (
        trace_simple_v0(trace)
        .with_columns(filename=pl.lit(fn))
        .with_columns(
            pl.col.filename.str.extract(r"[0-9]+-[0-9]+_[^_]+_[^_]+_([^\.]+)\.pk", 1).alias('problem'),
            pl.col.filename.str.extract(r"[0-9]+-[0-9]+_[^_]+_([^_]+)_[^\.]+\.pk", 1).alias('algo')
        )
        .pipe(_add_swdi_stats, trace, elmcy_ta.distance, prefix='elmcywt_', thresh=0.15)
        .pipe(_add_swdi_stats, trace, jplag_dist, prefix='jplag_', thresh=0.15)
        .pipe(_add_swdi_stats, trace, codet5p_ta.distance, prefix='codet5p_', thresh=0.05)
        .pipe(_add_swdi_stats, trace, openai_ta.distance, prefix='openai_', thresh=0.05)
        
        .with_columns(objective_direction = obj_direction)
        .with_columns(
            current_best_fitness = pl.when(pl.col.objective_direction == pl.lit('MAX')).then(_ROLLING_MAX_FITNESS).otherwise(_ROLLING_MIN_FITNESS)
        )
        # .with_columns(elmcy_bcid=pl.col.b_tidx.replace(cidx_map))
        # .with_columns(elmcy_acid=pl.col.a_tidx.replace(cidx_map))
        # trace_inherit_df(trace, elmcy=elmcy_ta.distance, codet5p=codet5p_ta.distance, openai=openai_ta.distance)
    )
    all_dfs.append( df )

df = pl.concat(all_dfs)
    

CPU times: user 5.86 s, sys: 79.6 ms, total: 5.94 s
Wall time: 5.99 s


In [148]:
import plotly.express as px

_dsts = ['elmcywt','codet5p']

px.box(
    (
        df
        .unpivot(
            index=['b_idx', 'problem', 'filename'],
            on=[f'{dst}_swdi_rolling' for dst in _dsts]+[f'{dst}_swdi_cumul' for dst in _dsts],
        )
        .with_columns(((pl.col.b_idx / 5).round() * 5).alias('b_idx_bin'))
        .rename({'value': 'entropy'})
    ),
    x='b_idx_bin',
    y='entropy',
    color='variable',
    facet_row='problem',
    # line_group='filename',
    boxmode='overlay',
    height=1000
)

## clusteranalysis test

In [4]:
def shannon_wiener_clusters(arts, dist_func, thresh=0.1, max_trace_id=np.inf):
    clusters = [] # list of list of artifacts
    for a in arts:
        if not a.is_solution or a.trace_id > max_trace_id:
            continue

        for c_idx, cl in enumerate(clusters):
            if not any([dist_func(a, mem) > thresh for mem in cl]):
                clusters[c_idx].append(a)
                break
        else:
            clusters.append([a])  # new cluster
    return clusters

In [5]:

from eallmancy.analysis.analyzer.utils import cosine_sim
import numpy as np

def _stability(lsx):
    return min(lsx, default=0.0)

def _atomic_persp_stability(atm, persp_id):
    other_entries = [e for e in atm.entries if e.soln_id!=persp_id]
    persp_entry = atm.get(persp_id)
    dsts = [cosine_sim(persp_entry.embedding, oe.embedding) for oe in other_entries]
    return _stability(dsts)

def atomic_stability(atm):
    persp_stabs = [_atomic_persp_stability(atm, pid) for pid in atm.solution_members()]
    return min(persp_stabs)


In [6]:
vault = 'divrs_fs'
all_dfs = []
for fn in os.listdir(TRACEVAULT_DIR+f'/{vault}'):
    trace = fetch_trace(vault, fn, max_traceid=100)
    if max([a.fitness for a in trace.list if a.is_solution]) == float('-inf'):
        continue
    pairwise_ta, codet5p_ta, openai_ta = fetch_traceanalyses(vault, fn)
    break

In [7]:
sw_clusters = list(sorted(shannon_wiener_clusters([a for a in trace.list if a.is_solution], pairwise_ta.distance, thresh=0.15), key=lambda ccl: len(ccl), reverse=True))
largest_cluster = sw_clusters[0]

In [11]:
import plotly.express as px
import polars as pl

px.bar(
    (
        pl.DataFrame(
            [dict(size=len(c)) for c in shannon_wiener_clusters([a for a in trace.list if a.is_solution], lambda a,b: pairwise_ta.distance(a,b, 'ignore'), thresh=0.10)]
        )
        .with_columns(pl.col.size.rank('dense').alias('size_rank'))
        .with_columns(pl.col.size_rank.rank(method='ordinal', descending=True).alias('rank_idx'))
        
    ),
    x='rank_idx',
    y='size'
)


In [49]:

for c in cluster_ta.cluster_traceids:
    print(c,':',[(atomic_stability(x), x.get(c).start_token, x.get(c).end_token) for x in cluster_ta._atoms[c]])

70 : [(0.9621333931504571, 0, 12), (0.9203368956086171, 13, 22), (0.9301766955757115, 23, 23), (0.9405214688528205, 24, 42), (1.0, 43, 43)]
101 : [(0.9621564416243269, 0, 12), (0.9204038872369167, 13, 22), (1.0, 23, 23), (0.9470296370666923, 24, 42), (0.5335204234094498, 43, 43)]
112 : [(0.9621333931504571, 0, 12), (0.0, 13, 14), (0.9203771083395162, 15, 24), (0.9572667413506173, 25, 44)]


In [63]:
## from eallmancy.analysis.analyzer.tokenstr_handling import simple_segm_substr, grab_programbody

# grab_programbody(trace[159].program)
print(simple_segm_substr(trace, cluster_ta._atoms[112][2].get(112), cluster_ta._tcmp))

    for i in range(n):
        for j in range(n):
            if i != j:
                # Calculate gain and avoid division by zero
                gain = prize[j] / (distance[i, j] + 1e-6)
                
                # Determine scaling factor based on maximum allowed distance
                scale = maxlen / (distance[i, j] + 1e-6) if distance[i, j] <= maxlen else 0


##  scratch

In [72]:
import plotly.express as px
from IPython.display import display

def inherited_dist(df, _distcol, _gran=0.025):
    fig = px.bar(
        (
            df
            .filter(pl.col.a_is_parent)
            .with_columns(pl.col(_distcol).alias('dist'))
            .with_columns(((pl.col.dist / _gran).round() * _gran).alias('dist_bin'))
            .group_by(['problem', 'b_classname', 'dist_bin']).len()
            .with_columns(pl.col.len.alias('count'))
            .with_columns((pl.col.count / pl.col.count.sum().over(['problem', 'b_classname'])).alias('count_norm'))
            .sort(['problem', 'b_classname'])
        ),
        x='dist_bin', y='count_norm', hover_data=['count'],
        facet_row='problem', facet_col='b_classname',
        title=f'[{_distcol}] Parent-Child Distances'
    )
    fig.update_yaxes(matches=None, autorange=True)
    return fig



display( inherited_dist(df, 'dist_elmcy') )
display( inherited_dist(df, 'dist_openai') ) 
display( inherited_dist(df, 'dist_codet5p') )
